In [2]:
import pandas as pd

def combine_counts(files, output_file):
    """
    Combines TT-seq counts files based on gene IDs.

    Parameters:
        files (list): List of file paths to the TT-seq counts files.
        output_file (str): Path to the output file.
    """
    # Initialize an empty DataFrame for the combined data
    combined_df = None
    
    # Loop through the files and join them on gene IDs
    for i, file_path in enumerate(files):
        # Load the current file as a DataFrame
        df = pd.read_csv(file_path, sep="\t", header=None, names=["GeneID", f"Sample_{i+1}"])
        
        # Merge with the combined DataFrame
        if combined_df is None:
            combined_df = df  # First file initializes the combined DataFrame
        else:
            combined_df = pd.merge(combined_df, df, on="GeneID", how="outer")
    
    # Add a header row with filenames
    header = ["GeneID"] + [f"Sample_{i+1}" for i in range(len(files))]
    
    # Save the combined DataFrame to the output file
    combined_df.to_csv(output_file, sep=",", index=False, header=header)


parent_dir = "Nascent_Results"
    
counts_files = [
    f"{parent_dir}/INTS8_IAA_minus_R1_counts.txt",
    f"{parent_dir}/INTS8_IAA_minus_R2_counts.txt",
    f"{parent_dir}/INTS8_IAA_minus_R3_counts.txt",
    f"{parent_dir}/INTS8_IAA_plus_R1_counts.txt",
    f"{parent_dir}/INTS8_IAA_plus_R2_counts.txt",
    f"{parent_dir}/INTS8_IAA_plus_R3_counts.txt"
]
output_file = f"{parent_dir}/INTS8_counts.csv"

combine_counts(counts_files, output_file)


In [1]:
##############
# Identify optimal transcripts
##############

import pandas as pd
from pyBigWig import open as open_bigwig

def calculate_coverage(bigwig_file, chrom, start, stop):
    """
    Calculate the percentage of a region covered by transcription signal in a bigWig file.

    Parameters:
        bigwig_file (str): Path to the bigWig file.
        chrom (str): Chromosome name.
        start (int): Start position of the region.
        stop (int): Stop position of the region.

    Returns:
        float: The percentage of the region covered by transcription signal.
    """
    with open_bigwig(bigwig_file) as bw:
        try:
            values = bw.values(chrom, start, stop)
        except:
            print(f"An exception happened on chr {chrom}:{start}:{stop}")
            return 0
        
        valid_values = [v for v in values if v is not None]
        if not valid_values:
            return 0
        return sum(valid_values) / len(valid_values) * 100

def get_optimal_transcripts(bed_file, bigwig_file, output_file):
    """
    Identify the optimal transcript for each gene based on transcription signal and length.

    Parameters:
        bed_file (str): Path to the input .bed file.
        bigwig_file (str): Path to the control bigWig file.
        output_file (str): Path to save the optimal transcripts.
    """
    # Load the bed file
    bed_df = pd.read_csv(bed_file, sep="\t")
    bed_df.columns = ["Chr", "Start", "Stop", "Strand", "Geneid", "Transcriptid", "Genename", "Genetype"]

    # Initialize a list to store optimal transcripts
    optimal_transcripts = []

    # Group by Geneid instead of Genename
    for geneid, group in bed_df.groupby("Geneid"):
        best_transcript = None
        best_score = 0

        # Iterate through transcripts for the current gene
        for _, row in group.iterrows():
            chrom = row["Chr"]
            start = row["Start"]
            stop = row["Stop"]
            length = stop - start

            # Calculate coverage
            coverage = calculate_coverage(bigwig_file, chrom, start, stop)

            # Calculate score as length * coverage
            score = length * (coverage / 100)

            # Update the best transcript
            if score > best_score:
                best_score = score
                best_transcript = row
        
        # If no transcript has coverage, select the longest transcript
        if best_transcript is None:
            # Ensure idxmax operates on a valid index
            longest_idx = (group["Stop"] - group["Start"]).idxmax()
            best_transcript = group.loc[longest_idx]
    
#         # If no transcript has coverage, select the longest transcript
#         if best_transcript is None:
#             best_transcript = group.loc[group["Stop"] - group["Start"].idxmax()]

        # Append the best transcript for the gene
        optimal_transcripts.append(best_transcript)

    # Convert the list of optimal transcripts to a DataFrame
    optimal_transcripts_df = pd.DataFrame(optimal_transcripts)

    # Save the results to a file
    optimal_transcripts_df.to_csv(output_file, sep="\t", index=False)
    print(f"Optimal transcripts saved to {output_file}")

# Usage parameters
bed_file = "unoptimized_transcripts_nochr.bed"
bigwig_file = "All_Samp.bigwig"
output_file = "IDEAL_transcripts.bed"

get_optimal_transcripts(bed_file, bigwig_file, output_file)

3589419241.py:43: DtypeWarning: Columns (0) have mixed types. Specify dtype option on import or set low_memory=False.
  bed_df = pd.read_csv(bed_file, sep="\t")


An exception happened on chr 1:169849631:169893896
An exception happened on chr 1:169853074:169888888
An exception happened on chr 1:169853074:169893959
An exception happened on chr 1:169794730:169804386
An exception happened on chr 1:169795040:169854080
An exception happened on chr 1:169795043:169804347
An exception happened on chr 1:169795409:169854080
An exception happened on chr 1:169795921:169853037
An exception happened on chr 1:27612064:27635185
An exception happened on chr 1:27612292:27626240
An exception happened on chr 1:27612300:27624062
An exception happened on chr 1:196651754:196701565
An exception happened on chr 1:196651791:196701541
An exception happened on chr 1:196651852:196737804
An exception happened on chr 1:196651852:196747504
An exception happened on chr 1:196651852:196747504
An exception happened on chr 1:196651878:196747504
An exception happened on chr 1:196651941:196747504
An exception happened on chr 1:196651998:196701566
An exception happened on chr 1:196651

An exception happened on chr 7:93424486:93574724
An exception happened on chr 7:93424539:93574730
An exception happened on chr 7:93426323:93559810
An exception happened on chr 7:26667068:26864590
An exception happened on chr 4:109560246:109688719
An exception happened on chr 7:27181157:27185232
An exception happened on chr 7:102473128:102478922
An exception happened on chr 7:11370365:11832198
An exception happened on chr 9:35104112:35115850
An exception happened on chr 9:35104117:35115862
An exception happened on chr 9:35104121:35111588
An exception happened on chr 9:35104121:35112392
An exception happened on chr 9:35104121:35116341
An exception happened on chr 9:35104123:35111574
An exception happened on chr 9:35104142:35111423
An exception happened on chr 7:107044705:107161811
An exception happened on chr 7:107045123:107161446
An exception happened on chr 7:95297676:95324532
An exception happened on chr 2:75662705:75710915
An exception happened on chr 2:75662708:75710985
An exception

An exception happened on chr 8:133454848:133571887
An exception happened on chr 8:133454853:133571925
An exception happened on chr 8:133458873:133571887
An exception happened on chr 8:22987417:23018441
An exception happened on chr 8:22995841:23020192
An exception happened on chr 8:22996773:23020509
An exception happened on chr 8:22999548:23020199
An exception happened on chr 2:36980895:37084372
An exception happened on chr 3:169966807:169998373
An exception happened on chr 3:169966808:169993831
An exception happened on chr 8:56067295:56074509
An exception happened on chr 8:56073042:56074506
An exception happened on chr 8:56073054:56074506
An exception happened on chr 8:56073054:56074510
An exception happened on chr 8:56073054:56074510
An exception happened on chr 8:56073073:56074356
An exception happened on chr 8:56073075:56074506
An exception happened on chr 8:56073316:56074498
An exception happened on chr 1:114716913:114757983
An exception happened on chr 1:114716916:114757933
An exc

An exception happened on chr 11:61513714:61581076
An exception happened on chr 11:61515313:61581148
An exception happened on chr 11:61518057:61580826
An exception happened on chr 11:61518627:61580838
An exception happened on chr 11:61518627:61580871
An exception happened on chr 11:61518627:61580872
An exception happened on chr 3:45388561:45554726
An exception happened on chr 3:45388564:45547609
An exception happened on chr 3:45388576:45549407
An exception happened on chr 3:45388836:45548599
An exception happened on chr 11:17086572:17169741
An exception happened on chr 11:17086575:17207986
An exception happened on chr 7:36389821:36453791
An exception happened on chr 7:36389862:36453791
An exception happened on chr 9:122941020:123104866
An exception happened on chr 2:65056354:65086957
An exception happened on chr 2:65056362:65081574
An exception happened on chr 2:65056366:65086971
An exception happened on chr 2:65056372:65086999
An exception happened on chr 2:65056383:65075245
An excepti

...

An exception happened on chr 11:56802084:56819708
An exception happened on chr 11:56802084:56820422
An exception happened on chr 6:167357166:167384510
An exception happened on chr 6:167372177:167384466
An exception happened on chr 6:167372968:167378092
An exception happened on chr 6:167372968:167384420
An exception happened on chr 6:167372968:167384482
An exception happened on chr 6:167372968:167384484
An exception happened on chr 6:167372968:167384484
An exception happened on chr 6:167380905:167384399
An exception happened on chr 6:167381113:167382960
An exception happened on chr 11:56667545:56674664
An exception happened on chr 11:56476287:56484839
An exception happened on chr 9:87772915:87786884
An exception happened on chr 7:43940895:44019149
An exception happened on chr 7:43951910:44019151
An exception happened on chr 7:43998999:44019207
An exception happened on chr 7:44011882:44038978
An exception happened on chr 7:44026951:44039008
An exception happened on chr 7:143062330:143063

An exception happened on chr 1:120519468:120536339
An exception happened on chr 1:120528387:120548357
An exception happened on chr 1:145572345:145607858
An exception happened on chr 6:52664366:52669155
An exception happened on chr 3:8682943:8693701
An exception happened on chr 6:28091137:28093664
An exception happened on chr 9:62376161:62435199
An exception happened on chr 9:62376517:62434385
An exception happened on chr 9:64016950:64061612
An exception happened on chr 2:86861825:86895042
An exception happened on chr 1:86634276:86655376
An exception happened on chr 5:178764861:178818435
An exception happened on chr 7:56875385:56882146
An exception happened on chr 2:94811046:94817801
An exception happened on chr 2:94867486:94947341
An exception happened on chr 7:55681074:55689301
An exception happened on chr 6:52939726:52973149
An exception happened on chr 7:5110184:5144512
An exception happened on chr 7:5121572:5144546
An exception happened on chr 3:133661926:133689006
An exception hap

An exception happened on chr 9:14921013:14993195
An exception happened on chr 9:14922736:14993155
An exception happened on chr 9:14987302:15146401
An exception happened on chr 9:27245684:27282793
An exception happened on chr 9:27278307:27284869
An exception happened on chr 3:198057531:198080671
An exception happened on chr 3:198058053:198080720
An exception happened on chr 6:25732451:25737513
An exception happened on chr 1:153793937:153795957
An exception happened on chr 1:153793947:153796302
An exception happened on chr 4:118591719:118609484
An exception happened on chr 4:118591727:118606562
An exception happened on chr 4:118591773:118633729
An exception happened on chr 4:119407967:119454638
An exception happened on chr 4:119409892:119413366
An exception happened on chr 4:119444395:119454630
An exception happened on chr 4:119444948:119451235
An exception happened on chr 4:119449378:119454647
An exception happened on chr 4:119449556:119454653
An exception happened on chr 4:119449567:11

An exception happened on chr 3:183884924:183887994
An exception happened on chr 5:137755740:137760740
An exception happened on chr 1:202861754:202875241
An exception happened on chr 9:19461160:19464524
An exception happened on chr 2:33722721:33727564
An exception happened on chr 2:33726061:33728207
An exception happened on chr 3:101686827:101700926
An exception happened on chr 3:101686827:101700926
An exception happened on chr 1:94613814:94820277
An exception happened on chr 1:94616377:94820266
An exception happened on chr 1:94679580:94820219
An exception happened on chr 1:94731743:94820192
An exception happened on chr 1:94836748:94855426
An exception happened on chr 11:2335135:2347685
An exception happened on chr 2:173338340:173356208
An exception happened on chr 9:65219987:65230861
An exception happened on chr 1:147172744:147179126
An exception happened on chr 6:31360865:31367354
An exception happened on chr 6:31362351:31366904
An exception happened on chr 11:3610324:3614752
An excep

Optimal transcripts saved to IDEAL_transcripts.bed


In [21]:
#####################
# Debugging optimal transcripts
#####################

import pandas as pd
from pyBigWig import open as open_bigwig
import numpy as np

def calculate_coverage(bigwig_file, chrom, start, stop):
    """
    Calculate the percentage of a region covered by transcription signal in a bigWig file.
    """
    # Ensure valid start and stop
    if pd.isna(chrom) or pd.isna(start) or pd.isna(stop):
        print(f"Skipping invalid region: chrom={chrom}, start={start}, stop={stop}")
        return float('nan')

    if start >= stop:
        print(f"Skipping invalid range: chrom={chrom}, start={start}, stop={stop}")
        return float('nan')

    gene_length = stop - start  # Fix incorrect length calculation

    with open_bigwig(bigwig_file) as bw:
        # Fix: Check if chromosome name is in BigWig file
        chroms = bw.chroms()
        if chrom not in chroms:
            print(f"Skipping unknown chromosome: {chrom}")
            return float('nan')

        try:
            values = bw.values(chrom, start, stop)
        except RuntimeError as e:
            print(f"BigWig error for {chrom}:{start}-{stop}: {e}")
            return float('nan')

        if values is None or len(values) == 0:
            print(f"No signal for {chrom}:{start}-{stop}")
            return float('nan')

        sum_signal = np.nansum(values)
        return abs(sum_signal / gene_length) * 100

def get_optimal_transcripts(bed_file, bigwig_file, output_file, debug_file):
    """
    Identify the optimal transcript for each gene based on transcription signal and length.
    Log intermediate calculations to a debug file.
    """
    # Load the bed file
    bed_df = pd.read_csv(bed_file, sep="\t")
    bed_df.columns = ["Chr", "Start", "Stop", "Strand", "Geneid", "Transcriptid", "Genename", "Genetype"]

    # Initialize a list to store optimal transcripts
    optimal_transcripts = []

    # Open the debug file to log intermediate results
    with open(debug_file, "w") as debug:
        debug.write("Geneid\tTranscriptid\tChr\tStart\tStop\tLength\tCoverage\tScore\n")

        # Group by Geneid instead of Genename
        for geneid, group in bed_df.groupby("Geneid"):
            best_transcript = None
            best_cov = 0

            # Iterate through transcripts for the current gene
            for _, row in group.iterrows():
                chrom = row["Chr"]
                start = row["Start"]
                stop = row["Stop"]
                length = stop - start

                # Calculate coverage
                coverage = calculate_coverage(bigwig_file, chrom, start, stop)

                # Calculate score as length * coverage
                #score = length * (coverage / 100)

                # Log calculations to the debug file
                debug.write(f"{geneid}\t{row['Transcriptid']}\t{chrom}\t{start}\t{stop}\t{length}\t{coverage:.2f}\n") # \t{score:.2f}\n")

                # Update the best transcript
                if coverage > best_cov:
                    best_cov = coverage
                    best_transcript = row

            # If no transcript has coverage, select the longest transcript
            if best_transcript is None:
                longest_idx = (group["Stop"] - group["Start"]).idxmax()
                best_transcript = group.loc[longest_idx]

            # Append the best transcript for the gene
            optimal_transcripts.append(best_transcript)

    # Convert the list of optimal transcripts to a DataFrame
    optimal_transcripts_df = pd.DataFrame(optimal_transcripts)

    # Save the results to a file
    optimal_transcripts_df.to_csv(output_file, sep="\t", index=False)
    print(f"Optimal transcripts saved to {output_file}")
    print(f"Intermediate calculations logged to {debug_file}")

# Usage parameters
bed_file = "unoptimized_transcripts_gr4kb.bed"
bigwig_file = "INTS1_minus_combAvg.bigwig"
output_file = "IDEAL_transcripts_gr4kb_nochr.bed"
debug_file = "debug_coverage_calculations.tsv"

get_optimal_transcripts(bed_file, bigwig_file, output_file, debug_file)


ipykernel_launcher.py:108: DtypeWarning: Columns (0) have mixed types.Specify dtype option on import or set low_memory=False.


Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 6
Skipping unknown chromosome: 6
Skipping

Skipping unknown chromosome: 16
Skipping unknown chromosome: 16
Skipping unknown chromosome: 17
Skipping unknown chromosome: 17
Skipping unknown chromosome: 17
Skipping unknown chromosome: 7
Skipping unknown chromosome: 2
Skipping unknown chromosome: 2
Skipping unknown chromosome: 2
Skipping unknown chromosome: 2
Skipping unknown chromosome: 2
Skipping unknown chromosome: 2
Skipping unknown chromosome: 7
Skipping unknown chromosome: 7
Skipping unknown chromosome: 7
Skipping unknown chromosome: 7
Skipping unknown chromosome: 7
Skipping unknown chromosome: 7
Skipping unknown chromosome: 7
Skipping unknown chromosome: 7
Skipping unknown chromosome: 7
Skipping unknown chromosome: 7
Skipping unknown chromosome: 7
Skipping unknown chromosome: 7
Skipping unknown chromosome: 7
Skipping unknown chromosome: 7
Skipping unknown chromosome: 7
Skipping unknown chromosome: 7
Skipping unknown chromosome: 16
Skipping unknown chromosome: 16
Skipping unknown chromosome: 16
Skipping unknown chromosome: 16

Skipping unknown chromosome: 6
Skipping unknown chromosome: 6
Skipping unknown chromosome: 1
Skipping unknown chromosome: 6
Skipping unknown chromosome: 6
Skipping unknown chromosome: 6
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 6
Skipping unknown chromosome: 6
Skipping unknown chromosome: 3
Skipping unknown chromosome: 3
Skipping unknown chromosome: 7
Skipping unknown chromosome: 7
Skipping unknown chromosome: 7
Skipping unknown chromosome: 7
Skipping unknown chromosome: 7
Skipping unknown chromosome: 7
Skipping unknown chromosome: 7
Skipping unknown chromosome: 7
Skipping unknown chromosome: 7
Skipping unknown chromosome: 7
Skipping

Skipping unknown chromosome: 17
Skipping unknown chromosome: 17
Skipping unknown chromosome: 17
Skipping unknown chromosome: 17
Skipping unknown chromosome: 7
Skipping unknown chromosome: 7
Skipping unknown chromosome: 17
Skipping unknown chromosome: 11
Skipping unknown chromosome: 11
Skipping unknown chromosome: 11
Skipping unknown chromosome: 11
Skipping unknown chromosome: 11
Skipping unknown chromosome: 11
Skipping unknown chromosome: 3
Skipping unknown chromosome: 3
Skipping unknown chromosome: 3
Skipping unknown chromosome: 3
Skipping unknown chromosome: 11
Skipping unknown chromosome: 11
Skipping unknown chromosome: 7
Skipping unknown chromosome: 7
Skipping unknown chromosome: 9
Skipping unknown chromosome: 12
Skipping unknown chromosome: 12
Skipping unknown chromosome: 12
Skipping unknown chromosome: 12
Skipping unknown chromosome: 12
Skipping unknown chromosome: 12
Skipping unknown chromosome: 12
Skipping unknown chromosome: 12
Skipping unknown chromosome: 12
Skipping unknown 

...

Skipping unknown chromosome: 17
Skipping unknown chromosome: 10
Skipping unknown chromosome: 17
Skipping unknown chromosome: 17
Skipping unknown chromosome: 1
Skipping unknown chromosome: 17
Skipping unknown chromosome: 10
Skipping unknown chromosome: 10
Skipping unknown chromosome: 10
Skipping unknown chromosome: 13
Skipping unknown chromosome: 13
Skipping unknown chromosome: 13
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 12
Skipping unknown chromosome: 6
Skipping unknown chromosome: 6
Skipping unknown chromosome: 13
Skipping unknown chromosome: 13
Skipping unknown chromosome: 6
Skipping unknown chromosome: 6
Skipping unknown chromosome: 9
Skipping unknown chromosome: 12
Skipping unknown chromosome: 13
Skipping unknown chromosome: 13
Skipping unknown chromosome: 13
Skipping unknown chromosome: 11
Skipping unknown chromosome: 6
Skipping unknown chromosome: 6
Skipping unknown chromosome: 11
Skipping unknown chromosome: 11
Skipping unknown c

Skipping unknown chromosome: 6
Skipping unknown chromosome: 12
Skipping unknown chromosome: 2
Skipping unknown chromosome: 10
Skipping unknown chromosome: 10
Skipping unknown chromosome: 2
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 2
Skipping unknown chromosome: 2
Skipping unknown chromosome: 2
Skipping unknown chromosome: 13
Skipping unknown chromosome: 10
Skipping unknown chromosome: 8
Skipping unknown chromosome: 1
Skipping unknown chromosome: 6
Skipping unknown chromosome: 17
Skipping unknown chromosome: 10
Skipping unknown chromosome: 10
Skipping unknown chromosome: 9
Skipping unknown chromosome: 9
Skipping unknown chromosome: 9
Skipping unknown chromosome: 9
Skipping unknown chromosome: 17
Skipping unknown chromosome: 17
Skipping unknown chromosome: 7
Skipping unknown chromosome: 7
Skipping unknown chromosome: 16
Skipping unknown chromosome: 16
Skipping unknown chromosome: 17
Skipping unknown chromosome: 17
Skipping unknown chromoso

Skipping unknown chromosome: 1
Skipping unknown chromosome: 7
Skipping unknown chromosome: 7
Skipping unknown chromosome: 7
Skipping unknown chromosome: 7
Skipping unknown chromosome: 2
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 7
Skipping unknown chromosome: 7
Skipping unknown chromosome: 7
Skipping unknown chromosome: 7
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 7
Skipping unknown chromosome: 7
Skipping unknown chromosome: 17
Skipping unknown chromosome: 17
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 2
Skipping unknown chromosome: 2
Skippi

Skipping unknown chromosome: 9
Skipping unknown chromosome: 6
Skipping unknown chromosome: 6
Skipping unknown chromosome: 6
Skipping unknown chromosome: 5
Skipping unknown chromosome: 7
Skipping unknown chromosome: 13
Skipping unknown chromosome: 7
Skipping unknown chromosome: 15
Skipping unknown chromosome: 16
Skipping unknown chromosome: 16
Skipping unknown chromosome: 3
Skipping unknown chromosome: 8
Skipping unknown chromosome: 4
Skipping unknown chromosome: 15
Skipping unknown chromosome: 14
Skipping unknown chromosome: 14
Skipping unknown chromosome: 14
Skipping unknown chromosome: 14
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 3
Skipping unknown chromosome: 3
Skipping unknown chromosome: 3
Skipping unknown chromosome: 3
Skipping unknown chromosome: 14
Skipping unknown chromosome: 14
Skipping unknown chromosome: 14
Skipping unknown chromosome: 8
Skipping unknown chromosome: 8
Skipping unknown chromosome: 17
Skipping unknown chromosom

Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 6
Skipping unknown chromosome: 10
Skipping unknown chromosome: 12
Skipping unknown chromosome: 8
Skipping unknown chromosome: 8
Skipping unknown chromosome: 12
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 3
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 1
Skipping unknown chromosome: 16
Skipping unknown chromosome: 17
Skipping unknown chromosome: 17
Skipping unknown chromosome: 17
Skipping unknown chromosome: 17
Skipping unknown chromosome: 11
Skipping unknown chromosome: 3
Skipping unknown chromosome: 14
Skipping unknown chromosome: 14
Skipping unknown chromosome: 14
Skipping unknown chromosome: 5
Skipping unknown chromosome: 5
Skipping unknown chromosome: 1
Skipping unknown chromosome: 6
Skipping unknown chromosome: 10
Skipping unknown chromosom

In [4]:
import pyBigWig
bigwig_file = "AllTimepoints_Ser2p_merged.bw"
bw = pyBigWig.open(bigwig_file)
print(bw.chroms())

{'1': 248956422, '2': 242193529, '3': 198295559, '4': 190214555, '5': 181538259, '6': 170805979, '7': 159345973, '8': 145138636, '9': 138394717, '10': 133797422, '11': 135086622, '12': 133275309, '13': 114364328, '14': 107043718, '15': 101991189, '16': 90338345, '17': 83257441, '18': 80373285, '19': 58617616, '20': 64444167, '21': 46709983, '22': 50818468, 'X': 156040895, 'Y': 57227415}


In [19]:
from statistics import median

bigwig_file = "INTS1_minus_combAvg.bigwig"
chrom = "21"
start = 34787801
stop = 34888690

with open_bigwig(bigwig_file) as bw:
    # Get signal values
    gene_length = stop - start
    values = bw.values(chrom, start, stop)
    if values is None or len(values) == 0:
        print(float('nan'))  # No valid values for this region

    # Filter out NaN values and calculate the mean
    mean_signal = np.nansum(values)
    print(mean_signal / gene_length)


0.04734662385379904


In [20]:
from statistics import median

bigwig_file = "INTS1_minus_combAvg.bigwig"
chrom = "21"
start = 34791786
stop = 34887183

with open_bigwig(bigwig_file) as bw:
    # Get signal values
    gene_length = stop - start
    values = bw.values(chrom, start, stop)
    if values is None or len(values) == 0:
        print(float('nan'))  # No valid values for this region

    # Filter out NaN values and calculate the mean
    mean_signal = np.nansum(values)
    print(mean_signal / gene_length)


0.047890234451738796


In [22]:
from statistics import median

bigwig_file = "INTS1_minus_combAvg.bigwig"
chrom = "21"
start = 34821279
stop = 34888690

with open_bigwig(bigwig_file) as bw:
    # Get signal values
    gene_length = stop - start
    values = bw.values(chrom, start, stop)
    if values is None or len(values) == 0:
        print(float('nan'))  # No valid values for this region

    # Filter out NaN values and calculate the mean
    mean_signal = np.nansum(values)
    print(mean_signal / gene_length)


0.05233824334887823


In [4]:
######################
# Gene body sections' fold change in nascent transcription signal
######################

import pandas as pd
import numpy as np
from pybedtools import BedTool
import subprocess

def analyze_transcription_changes(gene_file, treatment_signal, control_signal, output_file):
    """
    Analyze fold change in nascent transcription signals in different gene regions.

    Parameters:
        gene_file (str): Path to the curated gene list.
        treatment_signal (str): Path to the treatment signal file (bigWig or bedGraph).
        control_signal (str): Path to the control signal file (bigWig or bedGraph).
        output_file (str): Path to save the results.
    """
    # Load the gene and TSS/TTS data
    genes = pd.read_csv(gene_file, sep="\t")
    genes.columns = ["Chr", "Start", "Stop", "Strand", "Geneid", "Transcriptid", "Genename", "Genetype"]

    # Ensure Start and Stop are numeric
    genes["Start"] = pd.to_numeric(genes["Start"], errors="coerce")
    genes["Stop"] = pd.to_numeric(genes["Stop"], errors="coerce")
    
    # Drop invalid rows
    genes = genes.dropna(subset=["Start", "Stop"])
    genes = genes.drop_duplicates()
    
    # Reset index and ensure sorting
    sorted_genes = genes.sort_values(["Chr", "Start", "Stop"]).reset_index(drop=True)
    if not genes.reset_index(drop=True).equals(sorted_genes):
        print("Detected unsorted rows:")
        non_matching_rows = genes.reset_index(drop=True)[~genes.reset_index(drop=True).eq(sorted_genes).all(axis=1)]
        print(non_matching_rows)
        raise ValueError("The input data is not sorted. Automatically sorting data.")
    else:
        genes = sorted_genes  # Ensure the DataFrame is sorted
    
    # Verify sorting before processing
    if not genes.sort_values(["Chr", "Start", "Stop"]).equals(genes):
        raise ValueError("The input data is not sorted. Please ensure the data is sorted by Chr, Start, and Stop.")
    
    # Define regions based on TSS/TTS
    def calculate_regions(row):
        # Ensure Start and Stop are integers
        start = int(row["Start"])
        stop = int(row["Stop"])
    
        # Determine TSS and TTS based on strand
        tss = start if row["Strand"] == "+" else stop
        tts = stop if row["Strand"] == "+" else start

        # Calculate regions with strand-specific logic
        if row["Strand"] == "+":
            return {
                "Upstream": (row["Chr"], max(0, tss - 1000), tss), 
                "Promoter": (row["Chr"], tss, tss + 150), 
                "Early": (row["Chr"], tss + 250, tss + 2250), 
                "Mid": (row["Chr"], tss + 2250, tss + 5000), 
                "Late": (row["Chr"], tss + 5000, tts)
            }
        else:
            return {
                "Upstream": (row["Chr"], tss, tss + 1000),
                "Promoter": (row["Chr"], tss - 150, tss),
                "Early": (row["Chr"], tss - 2250, tss - 250),  
                "Mid": (row["Chr"], tss - 5000, tss - 2250),
                "Late": (row["Chr"], tts, tss - 5000)
            }
    
    genes["Regions"] = genes.apply(calculate_regions, axis=1)

    # Prepare BedTool objects for regions
    def regions_to_bed(region_type):
        bed_data = []
        for _, row in genes.iterrows():
            chr_, start, stop = row["Regions"][region_type]
            bed_data.append(f"{chr_}\t{start}\t{stop}\t{row['Geneid']}")
        return BedTool("\n".join(bed_data), from_string=True)

    regions = {key: regions_to_bed(key) for key in ["Upstream", "Promoter", "Early", "Mid", "Late"]}

    # Extract signal for treatment and control using bigWigAverageOverBed or bedtools map
    signal_data = {}
    def ensure_bed_sorted(bed):
        """
        Ensure a BedTool object is sorted. Returns a new sorted BedTool object.
        """
        return bed.sort()
    
    def ensure_file_sorted(file_path, output_path):
        """
        Ensure a file is sorted by chromosome and start position.
        """
        subprocess.run(
            f"LC_COLLATE=C sort -k1,1 -k2,2n {file_path} > {output_path}",
            shell=True, check=True
        )
        return output_path
    
    # Paths to signal files (ensure sorted versions exist)
    treatment_signal_sorted = ensure_file_sorted(treatment_signal, "treatment_signal_sorted.bedgraph")
    control_signal_sorted = ensure_file_sorted(control_signal, "control_signal_sorted.bedgraph")
    
    # Ensure regions are sorted
    for key, bed in regions.items():
        sorted_bed = ensure_bed_sorted(bed)
        
        # Map treatment and control signal
        treatment_values = sorted_bed.map(BedTool(treatment_signal_sorted), c=4, o="mean").to_dataframe()
        control_values = sorted_bed.map(BedTool(control_signal_sorted), c=4, o="mean").to_dataframe()
        
        # Store signal data
        signal_data[key] = {
            "Treatment": treatment_values.set_index("name")["score"],
            "Control": control_values.set_index("name")["score"]
        }

    # Calculate fold change for each region
    for key in signal_data.keys():
        # Ensure Treatment and Control are numeric
        signal_data[key]["Treatment"] = pd.to_numeric(signal_data[key]["Treatment"], errors="coerce").fillna(0)
        signal_data[key]["Control"] = pd.to_numeric(signal_data[key]["Control"], errors="coerce").fillna(0)
    
        # Calculate fold change
        signal_data[key]["FoldChange"] = np.log2(
            (signal_data[key]["Treatment"] + 1) / (signal_data[key]["Control"] + 1)
        )

    #print(signal_data)

    # Combine results into a single DataFrame without duplicating Geneid
    results = pd.concat(
        [
            pd.DataFrame({f"{key}_FoldChange": signal_data[key]["FoldChange"]})
            .assign(Geneid=signal_data[key]["Treatment"].index)
            for key in signal_data.keys()
        ],
        axis=1
    ).drop_duplicates(subset=["Geneid"])

    print(genes[10:])
    print(results[10:])
    
    # Drop duplicate columns in final_results
    results = results.loc[:, ~results.columns.duplicated()]
    
    # Merge fold change data with original gene info
    final_results = pd.merge(genes, results, on="Geneid", how="inner")

    # Categorize genes
    def categorize_changes(row):
        categories = []
        for key in ["Upstream", "Promoter", "Early", "Mid", "Late"]:
            if row[f"{key}_FoldChange"] > 1:
                categories.append(f"{key}_Upregulated")
            elif row[f"{key}_FoldChange"] < -1:
                categories.append(f"{key}_Downregulated")
        return "; ".join(categories)
    
    final_results["Categories"] = final_results.apply(categorize_changes, axis=1)
    
    # Save results to output file
    final_results.to_csv(output_file, sep="\t", index=False)
    print(f"Results saved to {output_file}")

# Usage
analyze_transcription_changes(
    gene_file="IDEAL_transcripts_gr10kb_sorted.bed",
    treatment_signal="INTS11_plus_combAvgSort.bedgraph",
    control_signal="INTS11_minus_combAvgSort.bedgraph",
    output_file="Regions.tsv"
)


      Chr     Start      Stop Strand              Geneid       Transcriptid  \
10      1    827721    854422      +  ENSG00000228794.12  ENST00000702098.1   
11      1    904834    914971      +   ENSG00000272438.1  ENST00000715285.1   
12      1    925731    944574      +  ENSG00000187634.13  ENST00000342066.8   
13      1    944203    959256      -  ENSG00000188976.11  ENST00000327044.7   
14      1   1001138   1014540      +  ENSG00000187608.10  ENST00000624697.4   
...    ..       ...       ...    ...                 ...                ...   
23095   Y  26508213  26579690      +   ENSG00000215506.5  ENST00000258589.8   
23096   Y  26594851  26634652      -   ENSG00000237917.1  ENST00000435945.1   
23097   Y  57067865  57130289      +   ENSG00000292366.1  ENST00000711260.1   
23098   Y  57184216  57197337      +   ENSG00000292373.1  ENST00000711286.1   
23099   Y  57190738  57208756      +   ENSG00000292369.1  ENST00000711268.1   

              Genename                Genetype  \
1

In [2]:
##############
# Identifying outliers in TTseq signal
##############

import pandas as pd
import numpy as np
import matplotlib.pyplot as plt

# Load the uncompressed matrix file (skipping the metadata lines)
matrix_file = "matrix_pm1kb_g15kb.tab"
matrix = pd.read_csv(matrix_file, sep="\t", comment="#", header=None)

# Flatten the matrix into a single array of values
values = matrix.iloc[:, 1:].values.flatten()  # Exclude the first column (region IDs)

# Convert to numeric, forcing invalid entries to NaN
values = pd.to_numeric(values, errors="coerce")

# Filter out NaN or infinite values
values = values[np.isfinite(values)]

# Plot the distribution
plt.figure(figsize=(10, 6))
plt.hist(values, bins=100, color='skyblue', edgecolor='black', log=True)
plt.title("Distribution of Signal Values")
plt.xlabel("Signal Intensity")
plt.ylabel("Frequency (log scale)")
plt.grid(True)
plt.show()

# Print summary statistics
print("Summary Statistics:")
print(f"Min: {np.min(values)}")
print(f"Max: {np.max(values)}")
print(f"Mean: {np.mean(values)}")
print(f"Median: {np.median(values)}")
print(f"95th Percentile: {np.percentile(values, 95)}")
print(f"99th Percentile: {np.percentile(values, 99)}")

297222546.py:11: DtypeWarning: Columns (0,1,2,3,4,5,6,7,8,9,10,11,12,13,14,15,16,17,18,19,20,21,22,23,24,25,26,27,28,29,30,31,32,33,34,35,36,37,38,39,40,41,42,43,44,45,46,47,48,49,50,51,52,53,54,55,56,57,58,59,60,61,62,63,64,65,66,67,68,69,70,71,72,73,74,75,76,77,78,79,80,81,82,83,84,85,86,87,88,89,90,91,92,93,94,95,96,97,98,99,100,101,102,103,104,105,106,107,108,109,110,111,112,113,114,115,116,117,118,119,120,121,122,123,124,125,126,127,128,129,130,131,132,133,134,135,136,137,138,139,140,141,142,143,144,145,146,147,148,149,150,151,152,153,154,155,156,157,158,159,160,161,162,163,164,165,166,167,168,169,170,171,172,173,174,175,176,177,178,179,180,181,182,183,184,185,186,187,188,189,190,191,192,193,194,195,196,197,198,199,200,201,202,203,204,205,206,207,208,209,210,211,212,213,214,215,216,217,218,219,220,221,222,223,224,225,226,227,228,229,230,231,232,233,234,235,236,237,238,239,240,241,242,243,244,245,246,247,248,249,250,251,252,253,254,255,256,257,258,259,260,261,262,263,264,265,266,26

Summary Statistics:
Min: 0.001619
Max: 2737.0
Mean: 0.08675469644391562
Median: 0.03275
95th Percentile: 0.2451
99th Percentile: 0.4988


In [5]:
#################
# Distribution of regions in conditions
#################

import pandas as pd
import matplotlib.pyplot as plt
import seaborn as sns

# Load the TSV file
file_path = "Regions.tsv"
data = pd.read_csv(file_path, sep="\t")

# Extract fold change columns and reshape for plotting
fold_change_columns = ["Upstream_FoldChange", "Promoter_FoldChange", "Early_FoldChange", "Mid_FoldChange", "Late_FoldChange"]
melted_data = data.melt(id_vars=["Geneid"], value_vars=fold_change_columns,
                        var_name="Region", value_name="FoldChange")

# Create a box plot (without individual points)
plt.figure(figsize=(10, 6))
sns.boxplot(x="Region", y="FoldChange", data=melted_data, palette="Set2", showfliers=True)

# Customize the plot
plt.title("Distribution of Fold Change Across Regions", fontsize=16)
plt.xlabel("Region", fontsize=14)
plt.ylabel("Fold Change", fontsize=14)
plt.xticks(rotation=45, fontsize=12)
plt.grid(axis="y", linestyle="--", alpha=0.7)
plt.ylim(-0.03,0.03)

# Show the plot
plt.tight_layout()
plt.show()




In [6]:
#####################
# Pie charts for numbers
#####################

import pandas as pd
import matplotlib.pyplot as plt

# Load the TSV file
file_path = "Regions.tsv"
data = pd.read_csv(file_path, sep="\t")

# Define fold change columns and cutoff values
fold_change_columns = ["Upstream_FoldChange", "Promoter_FoldChange", "Early_FoldChange", "Mid_FoldChange", "Late_FoldChange"]
cutoff_increase = 0.01
cutoff_decrease = -0.01

# Define colors
colors = {"Increasing": "pink", "Decreasing": "lightblue", "No Change": "lightgrey"}

# Function to categorize fold change
def categorize_fold_change(value):
    if value > cutoff_increase:
        return "Increasing"
    elif value < cutoff_decrease:
        return "Decreasing"
    else:
        return "No Change"

# Create pie charts for each region
for region in fold_change_columns:
    # Categorize the fold change values
    categories = data[region].apply(categorize_fold_change)
    
    # Count the number of genes in each category
    counts = categories.value_counts()
    
    # Create the pie chart
    plt.figure(figsize=(6, 6))
    plt.pie(counts, labels=counts.index, autopct="%1.1f%%", colors=[colors[cat] for cat in counts.index])
    plt.title(f"Fold Change Distribution: {region}", fontsize=16)
    
    # Show the plot
    plt.tight_layout()
    plt.savefig(f"regions_{region}_pie.png", format = 'png', dpi=300)
    plt.show()


In [13]:
import pandas as pd
import matplotlib.pyplot as plt
import numpy as np

# Load the TSV file
file_path = "Late_FC_N01.tsv"
data = pd.read_csv(file_path, sep="\t")

# Define fold change columns and cutoff values
fold_change_columns = ["Upstream_FoldChange", "Promoter_FoldChange", "Early_FoldChange", "Mid_FoldChange", "Late_FoldChange"]
cutoff_increase = 0.01
cutoff_decrease = -0.01

# Define colors
colors = {"Increasing": "pink", "Decreasing": "lightblue", "No Change": "lightgrey"}

# Function to categorize fold change
def categorize_fold_change(value):
    if value > cutoff_increase:
        return "Increasing"
    elif value < cutoff_decrease:
        return "Decreasing"
    else:
        return "No Change"

# Initialize a DataFrame to hold category counts for each region
category_counts = pd.DataFrame(index=["No Change", "Decreasing", "Increasing"], columns=fold_change_columns, data=0)

# Categorize and count for each region
for region in fold_change_columns:
    categories = data[region].apply(categorize_fold_change)
    counts = categories.value_counts()
    category_counts[region] = counts.reindex(["No Change", "Decreasing", "Increasing"], fill_value=0)

# Create the stacked bar plot
ax = category_counts.T.plot(kind="bar", stacked=True, color=[colors["No Change"], colors["Decreasing"], colors["Increasing"]], figsize=(10, 6))

# Customize the plot
plt.title("Fold Change Distribution Across Regions", fontsize=16)
plt.xlabel("Regions", fontsize=14)
plt.ylabel("Number of Genes", fontsize=14)
plt.xticks(rotation=45, fontsize=12)

# Move the legend to the side
plt.legend(title="Category", fontsize=12, loc="center left", bbox_to_anchor=(1.05, 0.5))

# Adjust layout to accommodate the legend
plt.tight_layout()

plt.savefig("Late_regions_N01.png", facecolor='white', format = 'png', dpi=300)

# Show the plot
plt.show()